<div align="center">

# FASHION-MNIST IMAGE CLASSIFICATION
### An Expanded, Professional ANN Workflow with PyTorch & Plotly

**ENHANCED EDITION · 70+ cells · Interactive Plotly dashboard**  

**Dataset:** `fmnist_small.csv` &nbsp; · &nbsp; **Task:** 10-class image classification &nbsp; · &nbsp; **Framework:** PyTorch

---

*A detailed, reproducible machine-learning project: deep data exploration, model diagnostics, evaluation, interpretability, and export.*

</div>

> **Project objective**  
> Build, train, and evaluate a fully connected neural network that classifies 28 × 28 grayscale clothing images. The notebook uses the supplied CSV as its source of truth, keeps the test set separate until final evaluation, and uses Plotly for interactive, presentation-ready charts.

**How to use this notebook**
1. Keep `fmnist_small.csv` in the same folder as this notebook (or update the path in the data-loading section).
2. Run the cells from top to bottom.
3. The first run trains the model and generates the evaluation charts. The final section saves the trained weights and metrics in an `artifacts/` folder.

**Expected environment:** Python 3.10+, PyTorch, pandas, NumPy, scikit-learn, Plotly, and Jupyter. A GPU is optional; the notebook automatically selects CUDA when available.

## 01 · Project map

| Stage | What happens | Deliverable |
|---|---|---|
| 1. Environment | Imports, reproducibility, device selection, chart theme | Consistent runtime |
| 2. Data audit | Read and validate the CSV; inspect labels, pixels, and duplicates | Data-quality profile |
| 3. Exploration | Class balance, brightness/contrast, class templates, image galleries, PCA | Colorful interactive Plotly EDA suite |
| 4. Preparation | Stratified train/validation/test split; normalization; DataLoaders | Leakage-aware data pipeline |
| 5. Model | Define and inspect a compact multilayer perceptron | ANN architecture |
| 6. Training | AdamW, learning-rate scheduling, early stopping, capacity pilot | Training curves + validation-only comparison |
| 7. Evaluation | ROC/PR, calibration, normalized confusion, risk–coverage, error review | Detailed model assessment |
| 8. Inference & export | Predict one image and save portable artifacts | `.pth`, `.json`, `.csv` |

### Important modeling decisions

- **No test-set tuning:** the validation split is used for early stopping; the test split is evaluated only after training.
- **Stratification:** each split retains approximately the same class proportions.
- **Logits, not softmax, enter the loss:** `CrossEntropyLoss` performs the required log-softmax internally.
- **Pixel normalization:** integer intensities in `[0, 255]` are converted to `float32` values in `[0, 1]`.
- **Class names:** label IDs follow the standard Fashion-MNIST class mapping. The CSV itself is still checked before training.

## 02 · Environment, imports & visual style

The notebook keeps dependencies explicit and uses one consistent Plotly theme. This makes charts look coherent when exported or viewed in Jupyter.

Install missing packages in your environment before continuing:

```bash
pip install numpy pandas scikit-learn plotly torch jupyter
```

In [1]:
# Core Python utilities
import copy
import json
import random
import time
import warnings
from pathlib import Path

# Data handling
import numpy as np
import pandas as pd

# Visualization
import plotly.express as px
import plotly.graph_objects as go
import plotly.io as pio
from plotly.subplots import make_subplots
from IPython.display import display, HTML

# Machine learning utilities
from sklearn.model_selection import train_test_split
from sklearn.metrics import (
    accuracy_score,
    classification_report,
    confusion_matrix,
    f1_score,
    precision_score,
    recall_score,
)

# PyTorch
import torch
import torch.nn as nn
from torch.utils.data import Dataset, DataLoader

warnings.filterwarnings("ignore", category=FutureWarning)
pd.set_option("display.max_columns", 20)
pd.set_option("display.precision", 4)

print(f"Python / NumPy / pandas ready | PyTorch {torch.__version__} | Plotly {pio.__version__ if hasattr(pio, '__version__') else 'available'}")

Python / NumPy / pandas ready | PyTorch 2.11.0+cu130 | Plotly available


In [2]:
# Reproducibility: make data splits and initialization repeatable.
SEED = 42

def seed_everything(seed: int = SEED) -> None:
    random.seed(seed)
    np.random.seed(seed)
    torch.manual_seed(seed)
    if torch.cuda.is_available():
        torch.cuda.manual_seed_all(seed)
    # Deterministic behavior is preferred for a learning notebook.
    torch.backends.cudnn.deterministic = True
    torch.backends.cudnn.benchmark = False

seed_everything(SEED)
DEVICE = torch.device("cuda" if torch.cuda.is_available() else "cpu")
print(f"Selected device: {DEVICE}")
if DEVICE.type == "cuda":
    print(f"GPU: {torch.cuda.get_device_name(0)}")

Selected device: cuda
GPU: Tesla T4


In [3]:
# A restrained, consistent visual system for all Plotly charts.
FASHION_COLORS = [
    "#2563EB",  # electric blue
    "#06B6D4",  # cyan
    "#8B5CF6",  # violet
    "#EC4899",  # magenta
    "#F97316",  # orange
    "#10B981",  # emerald
    "#EAB308",  # gold
    "#F43F5E",  # coral red
    "#6366F1",  # indigo
    "#84CC16",  # lime
]

fashion_template = go.layout.Template(
    layout=go.Layout(
        font=dict(family="Inter, Arial, sans-serif", size=13, color="#243247"),
        title=dict(font=dict(size=20, color="#142238"), x=0.02, xanchor="left"),
        paper_bgcolor="#FFFFFF",
        plot_bgcolor="#FBFCFF",
        colorway=FASHION_COLORS,
        margin=dict(l=55, r=30, t=75, b=55),
        xaxis=dict(showgrid=False, zeroline=False, linecolor="#D9E1EA", ticks="outside"),
        yaxis=dict(showgrid=True, gridcolor="#E9EEF4", zeroline=False, linecolor="#D9E1EA", ticks="outside"),
        legend=dict(bgcolor="rgba(255,255,255,0.75)", borderwidth=0),
        hoverlabel=dict(bgcolor="#142238", font=dict(color="white")),
    )
)

pio.templates["fashion_clean"] = fashion_template
pio.templates.default = "fashion_clean"

# Reusable notebook section header.
display(HTML("""
<div style="padding:14px 18px;border-left:5px solid #2563EB;background:#F3F7FC;border-radius:8px;margin:8px 0 18px 0;">
  <span style="font-size:12px;letter-spacing:1.6px;color:#2563EB;font-weight:700;">PROJECT WORKSPACE</span>
  <div style="font-size:20px;font-weight:700;color:#142238;margin-top:4px;">Fashion-MNIST · ANN Classification</div>
  <div style="font-size:13px;color:#526174;margin-top:4px;">Interactive analysis · Reproducible training · Transparent evaluation</div>
</div>
"""))

## 03 · Load the supplied dataset

The provided file is a compact Fashion-MNIST-style sample. It is expected to contain one target column named `label` and 784 pixel columns (`pixel1` through `pixel784`). The loader searches the notebook folder and common notebook runtime locations. If your file is elsewhere, change `DATA_PATH` manually.

In [4]:
# Locate the CSV. Keeping the file beside the notebook is the most portable option.
CANDIDATE_PATHS = [
    Path("fmnist_small.csv"),
    Path.cwd() / "fmnist_small.csv",
    Path("/mnt/data/fmnist_small.csv"),  # common hosted-notebook workspace
    Path("/content/fmnist_small.csv"),   # Google Colab
]

DATA_PATH = next((path for path in CANDIDATE_PATHS if path.exists()), None)
if DATA_PATH is None:
    raise FileNotFoundError(
        "Could not find fmnist_small.csv. Put it beside this notebook or update DATA_PATH. "
        "In Google Colab, upload the CSV into the current session first."
    )

print(f"Dataset path: {DATA_PATH.resolve()}")
df = pd.read_csv(DATA_PATH)
print(f"Loaded dataset: {df.shape[0]:,} rows × {df.shape[1]:,} columns")
display(df.head())

Dataset path: /content/fmnist_small.csv
Loaded dataset: 6,000 rows × 785 columns


,label,pixel1,pixel2,pixel3,pixel4,pixel5,pixel6,pixel7,pixel8,pixel9,...,pixel775,pixel776,pixel777,pixel778,pixel779,pixel780,pixel781,pixel782,pixel783,pixel784
0,9,0,0,0,0,0,0,0,0,0,...,0,7,0,50,205,196,213,165,0,0
1,7,0,0,0,0,0,0,0,0,0,...,0,0,0,0,0,0,0,0,0,0
2,0,0,0,0,0,0,1,0,0,0,...,142,142,142,21,0,3,0,0,0,0
3,8,0,0,0,0,0,0,0,0,0,...,0,0,0,0,0,0,0,0,0,0
4,8,0,0,0,0,0,0,0,0,0,...,213,203,174,151,188,10,0,0,0,0


In [5]:
# Validate the schema before any modeling step.
TARGET_COLUMN = "label"
PIXEL_COLUMNS = [column for column in df.columns if column != TARGET_COLUMN]

assert TARGET_COLUMN in df.columns, "Expected a target column named 'label'."
assert len(PIXEL_COLUMNS) == 784, f"Expected 784 pixel columns, found {len(PIXEL_COLUMNS)}."
assert df[TARGET_COLUMN].notna().all(), "Target column contains missing values."
assert not df[PIXEL_COLUMNS].isna().any().any(), "Pixel columns contain missing values."

labels_found = sorted(df[TARGET_COLUMN].astype(int).unique().tolist())
assert set(labels_found).issubset(set(range(10))), f"Unexpected label IDs: {labels_found}"

# Standard Fashion-MNIST label mapping.
CLASS_NAMES = {
    0: "T-shirt / Top",
    1: "Trouser",
    2: "Pullover",
    3: "Dress",
    4: "Coat",
    5: "Sandal",
    6: "Shirt",
    7: "Sneaker",
    8: "Bag",
    9: "Ankle boot",
}

# Convert once to predictable numeric types.
X_raw = df[PIXEL_COLUMNS].to_numpy(dtype=np.float32)
y = df[TARGET_COLUMN].to_numpy(dtype=np.int64)

assert np.isfinite(X_raw).all(), "Pixel matrix contains non-finite values."
assert X_raw.min() >= 0 and X_raw.max() <= 255, "Expected pixel intensities in the range [0, 255]."

print("Schema validation: PASSED")
print(f"Images: {len(df):,} | Image shape: 28 × 28 | Pixel features: {X_raw.shape[1]} | Classes present: {labels_found}")

Schema validation: PASSED
Images: 6,000 | Image shape: 28 × 28 | Pixel features: 784 | Classes present: [0, 1, 2, 3, 4, 5, 6, 7, 8, 9]


In [6]:
# Compact data-quality and class-summary table.
quality_summary = pd.DataFrame({
    "Check": [
        "Rows / images",
        "Pixel features per image",
        "Missing values",
        "Exact duplicate rows",
        "Pixel minimum",
        "Pixel maximum",
        "Target classes present",
    ],
    "Result": [
        f"{len(df):,}",
        f"{len(PIXEL_COLUMNS)}",
        f"{int(df.isna().sum().sum()):,}",
        f"{int(df.duplicated().sum()):,}",
        f"{X_raw.min():.0f}",
        f"{X_raw.max():.0f}",
        f"{len(labels_found)} / 10",
    ],
})
display(quality_summary.style.hide(axis="index").set_properties(**{"text-align": "left"}).set_table_styles([
    {"selector": "th", "props": [("background-color", "#142238"), ("color", "white"), ("font-weight", "bold"), ("padding", "9px")]},
    {"selector": "td", "props": [("padding", "8px"), ("border-bottom", "1px solid #E9EEF4")]},
]))

print("\nClass distribution:")
display(
    df[TARGET_COLUMN].value_counts().sort_index().rename("image_count").to_frame()
      .assign(class_name=lambda table: [CLASS_NAMES[int(i)] for i in table.index])
)

Check,Result
Rows / images,"6,000"
Pixel features per image,784
Missing values,0
Exact duplicate rows,1
Pixel minimum,0
Pixel maximum,255
Target classes present,10 / 10



Class distribution:


,image_count,class_name
label,,
0,595,T-shirt / Top
1,590,Trouser
2,604,Pullover
3,591,Dress
4,595,Coat
5,612,Sandal
6,656,Shirt
7,620,Sneaker
8,582,Bag


## 04 · Exploratory data analysis

Before building a neural network, inspect the class distribution, raw pixel intensity, and actual image samples. These checks catch common problems such as unexpected labels, constant pixels, or incorrectly reshaped images.

In [7]:
# 4.1 Class balance — counts and percentages.
class_counts = (
    df[TARGET_COLUMN].value_counts().sort_index().rename_axis("label").reset_index(name="image_count")
)
class_counts["class_name"] = class_counts["label"].map(CLASS_NAMES)
class_counts["percentage"] = class_counts["image_count"] / len(df) * 100

fig = px.bar(
    class_counts,
    x="class_name",
    y="image_count",
    color="class_name",
    text="image_count",
    category_orders={"class_name": [CLASS_NAMES[i] for i in range(10)]},
    title="Class distribution across the supplied dataset",
    labels={"class_name": "Fashion category", "image_count": "Number of images"},
)
fig.update_traces(textposition="outside", marker_line_width=0, showlegend=False)
fig.update_layout(height=470, xaxis_tickangle=-25, yaxis_title="Images", xaxis_title="")
fig.show()

print(f"Largest / smallest class ratio: {class_counts['image_count'].max() / class_counts['image_count'].min():.2f}×")

Largest / smallest class ratio: 1.18×


In [8]:
# 4.2 Pixel intensity profile. Sample pixels for a lighter, faster chart.
rng = np.random.default_rng(SEED)
pixel_sample = X_raw[rng.choice(len(X_raw), size=min(500, len(X_raw)), replace=False)].ravel()

fig = px.histogram(
    x=pixel_sample,
    nbins=48,
    marginal="box",
    title="Pixel intensity distribution (sample of images)",
    labels={"x": "Pixel intensity", "y": "Frequency"},
    opacity=0.88,
)
fig.update_traces(marker_line_width=0)
fig.update_layout(height=430, showlegend=False)
fig.show()

print(f"Pixel mean: {X_raw.mean():.2f} | Pixel standard deviation: {X_raw.std():.2f}")

Pixel mean: 73.11 | Pixel standard deviation: 89.96


In [9]:
# 4.3 A balanced 2-per-class image gallery (Plotly heatmaps are hoverable and zoomable).
preview_indices = []
for label_id in labels_found:
    candidates = np.flatnonzero(y == label_id)
    chosen = rng.choice(candidates, size=min(2, len(candidates)), replace=False)
    preview_indices.extend(chosen.tolist())

n_cols = 5
n_rows = int(np.ceil(len(preview_indices) / n_cols))
gallery = make_subplots(
    rows=n_rows,
    cols=n_cols,
    subplot_titles=[f"{CLASS_NAMES[int(y[idx])]} · ID {idx}" for idx in preview_indices],
    horizontal_spacing=0.035,
    vertical_spacing=0.10,
)

for position, idx in enumerate(preview_indices, start=1):
    row = (position - 1) // n_cols + 1
    col = (position - 1) % n_cols + 1
    image = X_raw[idx].reshape(28, 28)
    gallery.add_trace(
        go.Heatmap(z=image, colorscale="gray", zmin=0, zmax=255, showscale=False, hoverinfo="skip"),
        row=row,
        col=col,
    )

gallery.update_xaxes(visible=False, showgrid=False, zeroline=False)
gallery.update_yaxes(visible=False, showgrid=False, zeroline=False, autorange="reversed")
gallery.update_layout(
    title="Image gallery · two examples from each class",
    height=250 * n_rows,
    margin=dict(l=10, r=10, t=75, b=10),
)
gallery.show()

### EDA notes

- The source file contains **6,000 images**, each represented by 784 grayscale pixel intensities.
- The target distribution is broadly balanced; the class-count chart makes any differences visible.
- Pixel values are stored as integers from 0 to 255. They will be scaled to `[0, 1]` before entering the network.
- Duplicate rows are reported rather than silently removed. For this small educational dataset, the notebook preserves the supplied observations and documents the quality check.

### 04.4 · Deeper image-level statistics

The row-level statistics below turn each 28 × 28 image into a few interpretable measurements: **mean brightness**, **contrast** (pixel standard deviation), and **bright-pixel share**. These are descriptive signals, not replacements for the image itself. Comparing them by category can reveal systematic differences and potential dataset quirks.

In [10]:
# Build interpretable image-level statistics from the original 0–255 pixel matrix.
image_stats = pd.DataFrame({
    "label": y,
    "class_name": [CLASS_NAMES[int(label)] for label in y],
    "mean_brightness": X_raw.mean(axis=1),
    "contrast_std": X_raw.std(axis=1),
    "bright_pixel_share": (X_raw >= 128).mean(axis=1),
    "dark_pixel_share": (X_raw <= 16).mean(axis=1),
})

class_image_stats = image_stats.groupby(["label", "class_name"], as_index=False).agg(
    mean_brightness=("mean_brightness", "mean"),
    brightness_std=("mean_brightness", "std"),
    mean_contrast=("contrast_std", "mean"),
    mean_bright_share=("bright_pixel_share", "mean"),
    mean_dark_share=("dark_pixel_share", "mean"),
    image_count=("label", "size"),
)

display(class_image_stats.style.format({
    "mean_brightness": "{:.1f}", "brightness_std": "{:.1f}",
    "mean_contrast": "{:.1f}", "mean_bright_share": "{:.1%}",
    "mean_dark_share": "{:.1%}", "image_count": "{:.0f}"
}).background_gradient(subset=["mean_brightness", "mean_contrast"], cmap="Blues"))

,label,class_name,mean_brightness,brightness_std,mean_contrast,mean_bright_share,mean_dark_share,image_count
0,0,T-shirt / Top,83.4,28.3,82.1,35.9%,45.8%,595
1,1,Trouser,56.9,15.0,85.1,24.7%,66.4%,590
2,2,Pullover,97.3,32.9,82.2,40.8%,37.2%,604
3,3,Dress,66.2,21.7,85.3,28.7%,59.7%,591
4,4,Coat,99.4,26.7,91.1,44.6%,42.7%,595
5,5,Sandal,34.4,15.7,62.6,13.4%,73.9%,612
6,6,Shirt,85.4,33.3,76.9,34.8%,40.7%,656
7,7,Sneaker,43.1,12.4,72.8,18.0%,69.8%,620
8,8,Bag,89.4,28.1,87.1,40.2%,46.0%,582
9,9,Ankle boot,76.8,17.4,91.8,35.1%,55.7%,555


In [11]:
# Compare brightness and contrast distributions by category.
fig = make_subplots(rows=1, cols=2, subplot_titles=("Mean image brightness", "Within-image contrast"), horizontal_spacing=0.12)
for class_id, class_name in CLASS_NAMES.items():
    subset = image_stats[image_stats["label"] == class_id]
    color = FASHION_COLORS[class_id]
    fig.add_trace(go.Violin(
        x=[class_name] * len(subset), y=subset["mean_brightness"], name=class_name,
        legendgroup=class_name, showlegend=False, line_color=color, fillcolor=color,
        opacity=0.52, box_visible=True, meanline_visible=True,
        hovertemplate=f"{class_name}<br>Brightness: %{{y:.1f}}<extra></extra>"
    ), row=1, col=1)
    fig.add_trace(go.Violin(
        x=[class_name] * len(subset), y=subset["contrast_std"], name=class_name,
        legendgroup=class_name, showlegend=False, line_color=color, fillcolor=color,
        opacity=0.52, box_visible=True, meanline_visible=True,
        hovertemplate=f"{class_name}<br>Contrast: %{{y:.1f}}<extra></extra>"
    ), row=1, col=2)
fig.update_xaxes(tickangle=-45, title_text="Fashion category")
fig.update_yaxes(title_text="Average pixel intensity (0–255)", row=1, col=1)
fig.update_yaxes(title_text="Pixel standard deviation", row=1, col=2)
fig.update_layout(title="Image statistics by fashion category", height=560, showlegend=False)
fig.show()

In [12]:
# Treemap offers a second view of category balance with area and color encoding.
treemap_df = class_counts.copy()
fig = px.treemap(
    treemap_df, path=["class_name"], values="image_count", color="percentage",
    color_continuous_scale="Turbo", hover_data={"image_count": ":,", "percentage": ":.2f"},
    title="Dataset composition · category share"
)
fig.update_traces(
    texttemplate="<b>%{label}</b><br>%{value:,} images<br>%{percentRoot:.1%}",
    marker=dict(line=dict(color="white", width=3)),
)
fig.update_layout(height=470, coloraxis_colorbar=dict(title="Class share", ticksuffix="%"))
fig.show()

### 04.5 · What does a typical image look like?

Averaging images within a class produces a **class template**: brighter regions show pixels that tend to be active for that category. The standard-deviation template shows where examples vary most. These are aggregate summaries; they are not real individual garments.

In [13]:
# Calculate per-class mean and standard-deviation templates.
class_mean_images = np.stack([X_raw[y == class_id].mean(axis=0).reshape(28, 28) for class_id in range(10)])
class_std_images = np.stack([X_raw[y == class_id].std(axis=0).reshape(28, 28) for class_id in range(10)])

fig = make_subplots(rows=2, cols=5,
    subplot_titles=[f"{CLASS_NAMES[i]} · mean" for i in range(10)],
    horizontal_spacing=0.04, vertical_spacing=0.13)
for class_id in range(10):
    row, col = class_id // 5 + 1, class_id % 5 + 1
    fig.add_trace(go.Heatmap(
        z=class_mean_images[class_id], colorscale="Viridis", zmin=0, zmax=255,
        showscale=False, hovertemplate="Row %{y}, col %{x}<br>Mean intensity %{z:.1f}<extra></extra>"
    ), row=row, col=col)
fig.update_xaxes(visible=False); fig.update_yaxes(visible=False, autorange="reversed")
fig.update_layout(title="Class prototypes · mean pixel intensity", height=590, margin=dict(t=85, l=10, r=10, b=10))
fig.show()

In [14]:
fig = make_subplots(rows=2, cols=5,
    subplot_titles=[f"{CLASS_NAMES[i]} · variation" for i in range(10)],
    horizontal_spacing=0.04, vertical_spacing=0.13)
for class_id in range(10):
    row, col = class_id // 5 + 1, class_id % 5 + 1
    fig.add_trace(go.Heatmap(
        z=class_std_images[class_id], colorscale="Magma", showscale=False,
        hovertemplate="Row %{y}, col %{x}<br>Pixel std %{z:.1f}<extra></extra>"
    ), row=row, col=col)
fig.update_xaxes(visible=False); fig.update_yaxes(visible=False, autorange="reversed")
fig.update_layout(title="Class variation maps · pixel standard deviation", height=590, margin=dict(t=85, l=10, r=10, b=10))
fig.show()

In [15]:
# Global mean and standard-deviation maps describe the dataset's pixel-level structure.
global_mean_image = X_raw.mean(axis=0).reshape(28, 28)
global_std_image = X_raw.std(axis=0).reshape(28, 28)
fig = make_subplots(rows=1, cols=2, subplot_titles=("Global mean image", "Global pixel variability"), horizontal_spacing=0.12)
fig.add_trace(go.Heatmap(z=global_mean_image, colorscale="Viridis", colorbar=dict(title="Mean", x=0.45), hovertemplate="Pixel (%{y}, %{x})<br>Mean %{z:.1f}<extra></extra>"), row=1, col=1)
fig.add_trace(go.Heatmap(z=global_std_image, colorscale="Plasma", colorbar=dict(title="Std. dev.", x=1.02), hovertemplate="Pixel (%{y}, %{x})<br>Std %{z:.1f}<extra></extra>"), row=1, col=2)
fig.update_xaxes(visible=False); fig.update_yaxes(visible=False, autorange="reversed")
fig.update_layout(title="Dataset-wide pixel maps", height=420)
fig.show()

In [16]:
# A larger class-balanced gallery: four different examples per available class.
expanded_gallery_indices = []
for class_id in range(10):
    candidates = np.flatnonzero(y == class_id)
    expanded_gallery_indices.extend(rng.choice(candidates, size=min(4, len(candidates)), replace=False).tolist())

n_cols = 5
n_rows = int(np.ceil(len(expanded_gallery_indices) / n_cols))
expanded_gallery = make_subplots(rows=n_rows, cols=n_cols,
    subplot_titles=[f"{CLASS_NAMES[int(y[idx])]} · row {idx}" for idx in expanded_gallery_indices],
    horizontal_spacing=0.035, vertical_spacing=0.07)
for position, idx in enumerate(expanded_gallery_indices, start=1):
    row, col = (position - 1) // n_cols + 1, (position - 1) % n_cols + 1
    expanded_gallery.add_trace(go.Heatmap(z=X_raw[idx].reshape(28, 28), colorscale="gray", zmin=0, zmax=255, showscale=False, hoverinfo="skip"), row=row, col=col)
expanded_gallery.update_xaxes(visible=False); expanded_gallery.update_yaxes(visible=False, autorange="reversed")
expanded_gallery.update_layout(title="Expanded image gallery · four samples per category", height=260 * n_rows, margin=dict(t=90, l=10, r=10, b=10))
expanded_gallery.show()

### 04.6 · Explore the high-dimensional pixel space

A two-component PCA projection compresses the 784-dimensional pixel vectors into a two-dimensional view. It is a diagnostic visualization only: overlap does not mean that the classes are indistinguishable, and visible separation does not prove generalization. The chart is deliberately based on a reproducible sample to stay responsive.

In [17]:
from sklearn.decomposition import PCA

pca_sample_size = min(1800, len(X_raw))
pca_indices = rng.choice(len(X_raw), size=pca_sample_size, replace=False)
pca_model_raw = PCA(n_components=2, random_state=SEED)
pca_coordinates = pca_model_raw.fit_transform(X_raw[pca_indices] / 255.0)
pca_df = pd.DataFrame({
    "PC1": pca_coordinates[:, 0], "PC2": pca_coordinates[:, 1],
    "class_name": [CLASS_NAMES[int(value)] for value in y[pca_indices]],
    "label": y[pca_indices],
})
explained = pca_model_raw.explained_variance_ratio_.sum()
fig = px.scatter(
    pca_df, x="PC1", y="PC2", color="class_name", opacity=0.72,
    color_discrete_sequence=FASHION_COLORS, hover_data=["label"],
    title=f"PCA view of image pixels · first two components explain {explained:.1%} of sampled variance"
)
fig.update_traces(marker=dict(size=6, line=dict(width=0.35, color="white")))
fig.update_layout(height=560, legend_title="Fashion class")
fig.show()

In [18]:
# Brightness and contrast can reveal outliers, but should not be treated as class labels.
fig = px.scatter(
    image_stats, x="mean_brightness", y="contrast_std", color="class_name",
    color_discrete_sequence=FASHION_COLORS, opacity=0.62,
    hover_data={"label": True, "bright_pixel_share": ":.1%", "dark_pixel_share": ":.1%"},
    title="Image-level feature space · brightness versus contrast",
    labels={"mean_brightness": "Mean pixel intensity", "contrast_std": "Within-image pixel standard deviation", "class_name": "Category"}
)
fig.update_traces(marker=dict(size=7, line=dict(width=0.3, color="white")))
fig.update_layout(height=540)
fig.show()

## 05 · Train, validation & test preparation

A three-way split gives the model a clean validation set for model selection and a final test set for an unbiased holdout estimate. The test set is not used by the optimizer, scheduler, or early-stopping logic.

In [19]:
# First hold out the final test set; then carve validation data from the remaining training pool.
X_trainval_raw, X_test_raw, y_trainval, y_test = train_test_split(
    X_raw,
    y,
    test_size=0.20,
    random_state=SEED,
    stratify=y,
)

X_train_raw, X_val_raw, y_train, y_val = train_test_split(
    X_trainval_raw,
    y_trainval,
    test_size=0.15,
    random_state=SEED,
    stratify=y_trainval,
)

# Normalize uint8-like intensities to the [0, 1] interval.
X_train = X_train_raw / 255.0
X_val = X_val_raw / 255.0
X_test = X_test_raw / 255.0

split_summary = pd.DataFrame({
    "Split": ["Training", "Validation", "Test", "Total"],
    "Images": [len(y_train), len(y_val), len(y_test), len(y)],
    "Share": [len(y_train) / len(y), len(y_val) / len(y), len(y_test) / len(y), 1.0],
})
split_summary["Share"] = split_summary["Share"].map(lambda value: f"{value:.1%}")
display(split_summary.style.hide(axis="index").set_properties(**{"padding": "8px"}))

fig = go.Figure(go.Pie(
    labels=["Training", "Validation", "Test"],
    values=[len(y_train), len(y_val), len(y_test)],
    hole=0.62,
    textinfo="label+percent",
    marker=dict(colors=["#2563EB", "#0F766E", "#F59E0B"], line=dict(color="white", width=3)),
))
fig.update_layout(title="Dataset allocation", height=410, showlegend=False)
fig.add_annotation(text=f"{len(y):,}<br><span style='font-size:12px'>images</span>", x=0.5, y=0.5, showarrow=False, font=dict(size=22, color="#142238"))
fig.show()

assert X_train.min() >= 0 and X_train.max() <= 1
assert X_val.min() >= 0 and X_val.max() <= 1
assert X_test.min() >= 0 and X_test.max() <= 1

Split,Images,Share
Training,4080,68.0%
Validation,720,12.0%
Test,1200,20.0%
Total,6000,100.0%


In [20]:
class FashionDataset(Dataset):
    """PyTorch dataset for flattened 28 × 28 grayscale images."""

    def __init__(self, features: np.ndarray, labels: np.ndarray):
        if len(features) != len(labels):
            raise ValueError("Features and labels must contain the same number of rows.")
        self.features = torch.tensor(features, dtype=torch.float32)
        self.labels = torch.tensor(labels, dtype=torch.long)

    def __len__(self) -> int:
        return len(self.labels)

    def __getitem__(self, index: int):
        return self.features[index], self.labels[index]

BATCH_SIZE = 128

train_dataset = FashionDataset(X_train, y_train)
val_dataset = FashionDataset(X_val, y_val)
test_dataset = FashionDataset(X_test, y_test)

loader_generator = torch.Generator().manual_seed(SEED)
train_loader = DataLoader(train_dataset, batch_size=BATCH_SIZE, shuffle=True, generator=loader_generator, num_workers=0)
val_loader = DataLoader(val_dataset, batch_size=BATCH_SIZE, shuffle=False, num_workers=0)
test_loader = DataLoader(test_dataset, batch_size=BATCH_SIZE, shuffle=False, num_workers=0)

print(f"Training batches: {len(train_loader)} | Validation batches: {len(val_loader)} | Test batches: {len(test_loader)}")
first_features, first_labels = next(iter(train_loader))
print(f"Batch feature shape: {tuple(first_features.shape)} | Batch label shape: {tuple(first_labels.shape)}")

Training batches: 32 | Validation batches: 6 | Test batches: 10
Batch feature shape: (128, 784) | Batch label shape: (128,)


### 05.1 · Verify class balance across splits

Stratification should preserve the category mix across training, validation, and test partitions. This chart checks that assumption directly instead of relying on the split configuration alone.

In [21]:
split_frames = []
for split_name, split_labels in [("Training", y_train), ("Validation", y_val), ("Test", y_test)]:
    split_counts = pd.Series(split_labels).value_counts(normalize=True).reindex(range(10), fill_value=0)
    for class_id, share in split_counts.items():
        split_frames.append({"split": split_name, "class_name": CLASS_NAMES[int(class_id)], "share": share})
split_balance_df = pd.DataFrame(split_frames)
fig = px.bar(split_balance_df, x="class_name", y="share", color="split", barmode="group",
    color_discrete_map={"Training": "#2563EB", "Validation": "#06B6D4", "Test": "#F97316"},
    title="Class proportions are preserved across data splits",
    labels={"class_name": "Fashion category", "share": "Share within split", "split": "Split"})
fig.update_yaxes(tickformat=".0%")
fig.update_xaxes(tickangle=-28)
fig.update_layout(height=490, legend=dict(orientation="h", y=1.12))
fig.show()

In [22]:
# Visualize the effect of scaling pixel intensities from [0, 255] to [0, 1].
normalization_sample = rng.choice(X_train_raw.size, size=min(25000, X_train_raw.size), replace=False)
raw_values_sample = X_train_raw.ravel()[normalization_sample]
scaled_values_sample = raw_values_sample / 255.0
fig = go.Figure()
fig.add_trace(go.Histogram(x=raw_values_sample, nbinsx=45, name="Raw pixels · 0–255", opacity=0.68, marker_color="#2563EB"))
fig.add_trace(go.Histogram(x=scaled_values_sample, nbinsx=45, name="Scaled pixels · 0–1", opacity=0.68, marker_color="#F97316", xaxis="x2"))
fig.update_layout(
    title="Pixel normalization · same values on two scales", barmode="overlay", height=420,
    xaxis=dict(title="Raw intensity", domain=[0, 0.46]),
    xaxis2=dict(title="Normalized intensity", domain=[0.56, 1.0]),
    yaxis=dict(title="Frequency"),
    annotations=[dict(text="Raw scale", x=0.23, y=1.12, xref="paper", yref="paper", showarrow=False),
                 dict(text="Normalized scale", x=0.78, y=1.12, xref="paper", yref="paper", showarrow=False)]
)
fig.show()

In [23]:
# Inspect a real mini-batch after the Dataset and DataLoader are constructed.
batch_preview_count = min(15, len(first_features))
batch_preview = make_subplots(rows=3, cols=5,
    subplot_titles=[f"{CLASS_NAMES[int(first_labels[i])]} · y={int(first_labels[i])}" for i in range(batch_preview_count)],
    horizontal_spacing=0.04, vertical_spacing=0.10)
for i in range(batch_preview_count):
    row, col = i // 5 + 1, i % 5 + 1
    batch_preview.add_trace(go.Heatmap(z=first_features[i].numpy().reshape(28, 28), colorscale="gray", zmin=0, zmax=1, showscale=False, hoverinfo="skip"), row=row, col=col)
batch_preview.update_xaxes(visible=False); batch_preview.update_yaxes(visible=False, autorange="reversed")
batch_preview.update_layout(title="Mini-batch inspection · normalized tensors and labels", height=650, margin=dict(t=85, l=10, r=10, b=10))
batch_preview.show()

## 06 · Build the artificial neural network

The network is a **multilayer perceptron (MLP)**. Each 28 × 28 image is flattened into a 784-value vector. Three hidden fully connected layers learn increasingly useful feature combinations, while dropout helps reduce overfitting.

| Layer | Output width | Activation / role |
|---|---:|---|
| Input | 784 | Flattened grayscale pixels |
| Dense 1 | 256 | ReLU + Dropout (0.25) |
| Dense 2 | 128 | ReLU + Dropout (0.20) |
| Dense 3 | 64 | ReLU |
| Output | 10 | Raw class logits |

This is an ANN baseline, not a convolutional neural network. It treats the image as a vector, so it does not explicitly encode local spatial structure.

In [24]:
class FashionANN(nn.Module):
    """Fully connected baseline for 28 × 28 Fashion-MNIST images."""

    def __init__(self, input_features: int = 784, num_classes: int = 10):
        super().__init__()
        self.network = nn.Sequential(
            nn.Linear(input_features, 256),
            nn.ReLU(),
            nn.Dropout(p=0.25),
            nn.Linear(256, 128),
            nn.ReLU(),
            nn.Dropout(p=0.20),
            nn.Linear(128, 64),
            nn.ReLU(),
            nn.Linear(64, num_classes),
        )

    def forward(self, inputs: torch.Tensor) -> torch.Tensor:
        return self.network(inputs)

model = FashionANN(input_features=X_train.shape[1], num_classes=len(CLASS_NAMES)).to(DEVICE)
criterion = nn.CrossEntropyLoss()
optimizer = torch.optim.AdamW(model.parameters(), lr=1e-3, weight_decay=1e-4)
scheduler = torch.optim.lr_scheduler.ReduceLROnPlateau(
    optimizer, mode="min", factor=0.5, patience=2, min_lr=1e-5
)

parameter_count = sum(parameter.numel() for parameter in model.parameters() if parameter.requires_grad)
print(model)
print(f"\nTrainable parameters: {parameter_count:,}")

FashionANN(
  (network): Sequential(
    (0): Linear(in_features=784, out_features=256, bias=True)
    (1): ReLU()
    (2): Dropout(p=0.25, inplace=False)
    (3): Linear(in_features=256, out_features=128, bias=True)
    (4): ReLU()
    (5): Dropout(p=0.2, inplace=False)
    (6): Linear(in_features=128, out_features=64, bias=True)
    (7): ReLU()
    (8): Linear(in_features=64, out_features=10, bias=True)
  )
)

Trainable parameters: 242,762


### 06.1 · Model structure and parameter budget

The layer-width diagram communicates the shape of the network, while the parameter chart reveals where trainable weights are concentrated. Link widths in the Sankey view are proportional to the number of connections between adjacent layers; they are not a visualization of every individual neuron connection.

In [25]:
linear_layers = [(name, module) for name, module in model.named_modules() if isinstance(module, nn.Linear)]
layer_records = []
for layer_index, (layer_name, layer_module) in enumerate(linear_layers):
    weight_count = layer_module.weight.numel()
    bias_count = layer_module.bias.numel() if layer_module.bias is not None else 0
    layer_records.append({
        "layer": f"Dense {layer_index + 1}", "input_units": layer_module.in_features,
        "output_units": layer_module.out_features, "weights": weight_count,
        "biases": bias_count, "parameters": weight_count + bias_count,
    })
layer_parameter_df = pd.DataFrame(layer_records)
display(layer_parameter_df.style.format({"weights": "{:,}", "biases": "{:,}", "parameters": "{:,}"}).background_gradient(subset=["parameters"], cmap="Blues"))

fig = go.Figure(go.Sankey(
    arrangement="snap",
    node=dict(label=["Input<br>784", "Hidden 1<br>256", "Hidden 2<br>128", "Hidden 3<br>64", "Output<br>10"],
              color=["#0EA5E9", "#2563EB", "#8B5CF6", "#EC4899", "#F97316"], pad=24, thickness=24,
              line=dict(color="white", width=1.5)),
    link=dict(source=[0, 1, 2, 3], target=[1, 2, 3, 4],
              value=[784*256, 256*128, 128*64, 64*10],
              color=["rgba(37,99,235,0.32)", "rgba(139,92,246,0.32)", "rgba(236,72,153,0.32)", "rgba(249,115,22,0.32)"])
))
fig.update_layout(title="ANN architecture · layer widths and connection density", height=430, font=dict(size=13))
fig.show()

,layer,input_units,output_units,weights,biases,parameters
0,Dense 1,784,256,"200,704",256,"200,960"
1,Dense 2,256,128,"32,768",128,"32,896"
2,Dense 3,128,64,"8,192",64,"8,256"
3,Dense 4,64,10,640,10,650


In [26]:
fig = px.bar(layer_parameter_df, x="layer", y="parameters", color="layer", text="parameters",
    color_discrete_sequence=FASHION_COLORS, title="Trainable parameters by dense layer",
    labels={"layer": "Network layer", "parameters": "Number of parameters"})
fig.update_traces(texttemplate="%{text:,}", textposition="outside", marker_line_width=0)
fig.update_layout(height=430, showlegend=False)
fig.show()

In [27]:
# Inspect initialized / trained weight distributions per dense layer.
weight_distribution_fig = go.Figure()
for index, (layer_name, layer_module) in enumerate(linear_layers):
    values = layer_module.weight.detach().cpu().numpy().ravel()
    weight_distribution_fig.add_trace(go.Histogram(
        x=values, name=f"Dense {index + 1} ({layer_module.in_features}→{layer_module.out_features})",
        opacity=0.55, nbinsx=55, marker_color=FASHION_COLORS[index]
    ))
weight_distribution_fig.update_layout(
    title="Learned weight distributions by dense layer", barmode="overlay", height=450,
    xaxis_title="Weight value", yaxis_title="Frequency", legend=dict(orientation="h", y=1.15)
)
weight_distribution_fig.show()

## 07 · Train the model

Training uses **AdamW** with a starting learning rate of `0.001`. The learning-rate scheduler reduces the rate when validation loss stops improving. Early stopping ends training after several validation checks without meaningful improvement, and the best validation-loss weights are restored before testing.

The training loop records epoch-level loss, accuracy, learning rate, and duration. This makes the learning process auditable rather than hiding it behind a single final score.

In [28]:
# Hyperparameters — adjust these deliberately, then rerun from the model-definition cell.
EPOCHS = 30
EARLY_STOPPING_PATIENCE = 6
MIN_IMPROVEMENT = 1e-4

history = []
best_val_loss = float("inf")
best_state = None
wait = 0
start_time = time.time()

for epoch in range(1, EPOCHS + 1):
    epoch_start = time.time()

    # -------------------- Training --------------------
    model.train()
    train_loss_sum = 0.0
    train_correct = 0
    train_total = 0

    for batch_features, batch_labels in train_loader:
        batch_features = batch_features.to(DEVICE)
        batch_labels = batch_labels.to(DEVICE)

        optimizer.zero_grad(set_to_none=True)
        logits = model(batch_features)
        loss = criterion(logits, batch_labels)
        loss.backward()
        nn.utils.clip_grad_norm_(model.parameters(), max_norm=5.0)
        optimizer.step()

        batch_size = batch_labels.size(0)
        train_loss_sum += loss.item() * batch_size
        train_correct += (logits.argmax(dim=1) == batch_labels).sum().item()
        train_total += batch_size

    train_loss = train_loss_sum / train_total
    train_accuracy = train_correct / train_total

    # ------------------ Validation --------------------
    model.eval()
    val_loss_sum = 0.0
    val_correct = 0
    val_total = 0

    with torch.no_grad():
        for batch_features, batch_labels in val_loader:
            batch_features = batch_features.to(DEVICE)
            batch_labels = batch_labels.to(DEVICE)
            logits = model(batch_features)
            loss = criterion(logits, batch_labels)

            batch_size = batch_labels.size(0)
            val_loss_sum += loss.item() * batch_size
            val_correct += (logits.argmax(dim=1) == batch_labels).sum().item()
            val_total += batch_size

    val_loss = val_loss_sum / val_total
    val_accuracy = val_correct / val_total
    scheduler.step(val_loss)
    current_lr = optimizer.param_groups[0]["lr"]
    epoch_seconds = time.time() - epoch_start

    history.append({
        "epoch": epoch,
        "train_loss": train_loss,
        "val_loss": val_loss,
        "train_accuracy": train_accuracy,
        "val_accuracy": val_accuracy,
        "learning_rate": current_lr,
        "epoch_seconds": epoch_seconds,
    })

    # Keep a CPU copy of the best validation checkpoint.
    if val_loss < best_val_loss - MIN_IMPROVEMENT:
        best_val_loss = val_loss
        best_state = {key: value.detach().cpu().clone() for key, value in model.state_dict().items()}
        wait = 0
        checkpoint_note = "  ← best checkpoint"
    else:
        wait += 1
        checkpoint_note = ""

    print(
        f"Epoch {epoch:02d}/{EPOCHS} | "
        f"train loss {train_loss:.4f} · train acc {train_accuracy:.1%} | "
        f"val loss {val_loss:.4f} · val acc {val_accuracy:.1%} | "
        f"lr {current_lr:.2e} | {epoch_seconds:.1f}s{checkpoint_note}"
    )

    if wait >= EARLY_STOPPING_PATIENCE:
        print(f"\nEarly stopping: validation loss did not improve for {EARLY_STOPPING_PATIENCE} consecutive epochs.")
        break

if best_state is None:
    raise RuntimeError("Training did not produce a valid checkpoint.")

model.load_state_dict(best_state)
model.to(DEVICE)
model.eval()

history_df = pd.DataFrame(history)
training_seconds = time.time() - start_time
best_epoch = int(history_df.loc[history_df["val_loss"].idxmin(), "epoch"])
print(f"\nTraining complete in {training_seconds:.1f}s | Best epoch: {best_epoch} | Best validation loss: {best_val_loss:.4f}")

Epoch 01/30 | train loss 1.7106 · train acc 36.4% | val loss 1.0262 · val acc 56.8% | lr 1.00e-03 | 0.8s  ← best checkpoint
Epoch 02/30 | train loss 0.9596 · train acc 60.3% | val loss 0.8259 · val acc 65.6% | lr 1.00e-03 | 0.1s  ← best checkpoint
Epoch 03/30 | train loss 0.7994 · train acc 68.1% | val loss 0.7427 · val acc 70.1% | lr 1.00e-03 | 0.1s  ← best checkpoint
Epoch 04/30 | train loss 0.7131 · train acc 72.3% | val loss 0.6803 · val acc 71.9% | lr 1.00e-03 | 0.1s  ← best checkpoint
Epoch 05/30 | train loss 0.6455 · train acc 75.4% | val loss 0.6214 · val acc 74.7% | lr 1.00e-03 | 0.1s  ← best checkpoint
Epoch 06/30 | train loss 0.5870 · train acc 78.6% | val loss 0.5717 · val acc 77.8% | lr 1.00e-03 | 0.1s  ← best checkpoint
Epoch 07/30 | train loss 0.5426 · train acc 80.0% | val loss 0.5616 · val acc 79.6% | lr 1.00e-03 | 0.1s  ← best checkpoint
Epoch 08/30 | train loss 0.5121 · train acc 81.1% | val loss 0.5456 · val acc 80.6% | lr 1.00e-03 | 0.1s  ← best checkpoint
Epoch 09

In [29]:
# Plotly training dashboard: loss and accuracy use separate, readable panels.
fig = make_subplots(
    rows=1,
    cols=2,
    subplot_titles=("Loss by epoch", "Accuracy by epoch"),
    horizontal_spacing=0.12,
)

fig.add_trace(go.Scatter(
    x=history_df["epoch"], y=history_df["train_loss"], name="Training loss",
    mode="lines+markers", line=dict(width=3, color="#2563EB"), marker=dict(size=6),
), row=1, col=1)
fig.add_trace(go.Scatter(
    x=history_df["epoch"], y=history_df["val_loss"], name="Validation loss",
    mode="lines+markers", line=dict(width=3, color="#F59E0B"), marker=dict(size=6),
), row=1, col=1)
fig.add_trace(go.Scatter(
    x=history_df["epoch"], y=history_df["train_accuracy"], name="Training accuracy",
    mode="lines+markers", line=dict(width=3, color="#0F766E"), marker=dict(size=6),
), row=1, col=2)
fig.add_trace(go.Scatter(
    x=history_df["epoch"], y=history_df["val_accuracy"], name="Validation accuracy",
    mode="lines+markers", line=dict(width=3, color="#8B5CF6"), marker=dict(size=6),
), row=1, col=2)

fig.update_xaxes(title_text="Epoch", dtick=1, row=1, col=1)
fig.update_xaxes(title_text="Epoch", dtick=1, row=1, col=2)
fig.update_yaxes(title_text="Cross-entropy loss", row=1, col=1)
fig.update_yaxes(title_text="Accuracy", tickformat=".0%", range=[0, 1], row=1, col=2)
fig.update_layout(title="Training diagnostics", height=470, hovermode="x unified", legend=dict(orientation="h", y=-0.22))
fig.show()

### How to read the learning curves

- Training and validation loss should generally decrease as the network learns.
- A widening gap where training loss improves but validation loss worsens can indicate overfitting.
- Validation accuracy is more useful than training accuracy for selecting a checkpoint.
- A changing learning-rate trace can help explain plateaus or later improvements.

In [30]:
fig = px.line(
    history_df,
    x="epoch",
    y="learning_rate",
    markers=True,
    title="Learning-rate schedule",
    labels={"epoch": "Epoch", "learning_rate": "Learning rate"},
)
fig.update_traces(line=dict(width=3, color="#E76F51"), marker=dict(size=7))
fig.update_yaxes(type="log")
fig.update_layout(height=350)
fig.show()

### 07.1 · Training diagnostics beyond accuracy

A model can achieve a good headline score while showing a widening train/validation gap or unstable epoch times. These additional views make overfitting and optimization behavior easier to inspect.

In [31]:
# Generalization gap = training metric minus validation metric.
training_diagnostics = history_df.copy()
training_diagnostics["accuracy_gap"] = training_diagnostics["train_accuracy"] - training_diagnostics["val_accuracy"]
training_diagnostics["loss_gap"] = training_diagnostics["val_loss"] - training_diagnostics["train_loss"]

fig = make_subplots(rows=1, cols=2, subplot_titles=("Accuracy gap", "Loss gap"), horizontal_spacing=0.12)
fig.add_trace(go.Bar(x=training_diagnostics["epoch"], y=training_diagnostics["accuracy_gap"],
    marker_color=np.where(training_diagnostics["accuracy_gap"] >= 0, "#F97316", "#06B6D4"), name="Train − validation accuracy"), row=1, col=1)
fig.add_trace(go.Bar(x=training_diagnostics["epoch"], y=training_diagnostics["loss_gap"],
    marker_color=np.where(training_diagnostics["loss_gap"] >= 0, "#8B5CF6", "#10B981"), name="Validation − train loss"), row=1, col=2)
fig.add_hline(y=0, line_dash="dash", line_color="#64748B", row=1, col=1)
fig.add_hline(y=0, line_dash="dash", line_color="#64748B", row=1, col=2)
fig.update_xaxes(title_text="Epoch")
fig.update_yaxes(title_text="Difference", tickformat=".1%", row=1, col=1)
fig.update_yaxes(title_text="Cross-entropy loss difference", row=1, col=2)
fig.update_layout(title="Generalization-gap diagnostics", height=440, showlegend=False)
fig.show()

In [32]:
fig = px.bar(history_df, x="epoch", y="epoch_seconds", color="epoch_seconds",
    color_continuous_scale="Turbo", text_auto=".2f",
    title="Training time per epoch", labels={"epoch": "Epoch", "epoch_seconds": "Seconds"})
fig.update_traces(marker_line_width=0)
fig.update_layout(height=390, coloraxis_colorbar=dict(title="Seconds"))
fig.show()

In [33]:
# Put training loss and validation loss on a log axis to highlight late-stage changes.
fig = go.Figure()
fig.add_trace(go.Scatter(x=history_df["epoch"], y=history_df["train_loss"], mode="lines+markers", name="Train", line=dict(color="#2563EB", width=3)))
fig.add_trace(go.Scatter(x=history_df["epoch"], y=history_df["val_loss"], mode="lines+markers", name="Validation", line=dict(color="#F97316", width=3)))
fig.add_vline(x=best_epoch, line_dash="dot", line_color="#8B5CF6", annotation_text=f"Best epoch {best_epoch}", annotation_position="top right")
fig.update_yaxes(type="log", title="Loss · logarithmic scale")
fig.update_xaxes(title="Epoch", dtick=1)
fig.update_layout(title="Loss trajectory · detail view", height=430, hovermode="x unified")
fig.show()

### 07.2 · Controlled model-capacity experiment (validation only)

To make the baseline more informative, this optional experiment trains two alternative MLP sizes using the **same training and validation splits**. It does not use the test set, and it does not replace the primary model checkpoint. The results are a quick capacity comparison, not an exhaustive hyperparameter search.

In [34]:
class CandidateANN(nn.Module):
    def __init__(self, widths, dropout=0.15):
        super().__init__()
        blocks = []
        in_features = 784
        for width in widths:
            blocks.extend([nn.Linear(in_features, width), nn.ReLU(), nn.Dropout(dropout)])
            in_features = width
        blocks.append(nn.Linear(in_features, 10))
        self.network = nn.Sequential(*blocks)
    def forward(self, x):
        return self.network(x)

def run_validation_candidate(name, widths, max_epochs=12, learning_rate=1e-3):
    candidate = CandidateANN(widths).to(DEVICE)
    candidate_optimizer = torch.optim.AdamW(candidate.parameters(), lr=learning_rate, weight_decay=1e-4)
    best_loss, best_accuracy, best_epoch_candidate = float("inf"), 0.0, 0
    candidate_history = []
    for epoch in range(1, max_epochs + 1):
        candidate.train()
        for xb, yb in train_loader:
            xb, yb = xb.to(DEVICE), yb.to(DEVICE)
            candidate_optimizer.zero_grad(set_to_none=True)
            loss = criterion(candidate(xb), yb)
            loss.backward()
            candidate_optimizer.step()
        candidate.eval()
        val_losses, val_true_list, val_pred_list = [], [], []
        with torch.no_grad():
            for xb, yb in val_loader:
                xb = xb.to(DEVICE)
                logits = candidate(xb)
                val_losses.append(criterion(logits, yb.to(DEVICE)).item() * len(yb))
                val_true_list.append(yb.numpy())
                val_pred_list.append(logits.argmax(1).cpu().numpy())
        yv = np.concatenate(val_true_list); pv = np.concatenate(val_pred_list)
        val_loss_value = float(sum(val_losses) / len(yv))
        val_acc_value = float(accuracy_score(yv, pv))
        candidate_history.append({"model": name, "epoch": epoch, "val_loss": val_loss_value, "val_accuracy": val_acc_value})
        if val_loss_value < best_loss:
            best_loss, best_accuracy, best_epoch_candidate = val_loss_value, val_acc_value, epoch
    return {"model": name, "architecture": " → ".join(map(str, [784] + list(widths) + [10])),
            "best_val_loss": best_loss, "val_accuracy_at_best_loss": best_accuracy,
            "best_epoch": best_epoch_candidate, "parameters": sum(p.numel() for p in candidate.parameters())}, candidate_history

candidate_specs = [("Compact MLP", [128, 64]), ("Wide MLP", [512, 256, 128])]
candidate_results, candidate_histories = [], []
for candidate_index, (candidate_name, candidate_widths) in enumerate(candidate_specs):
    seed_everything(SEED + 100 + candidate_index)
    result, candidate_history = run_validation_candidate(candidate_name, candidate_widths)
    candidate_results.append(result); candidate_histories.extend(candidate_history)

candidate_results_df = pd.DataFrame(candidate_results)
candidate_histories_df = pd.DataFrame(candidate_histories)
display(candidate_results_df.style.format({"best_val_loss": "{:.4f}", "val_accuracy_at_best_loss": "{:.1%}", "parameters": "{:,}"}).background_gradient(subset=["val_accuracy_at_best_loss"], cmap="GnBu"))

,model,architecture,best_val_loss,val_accuracy_at_best_loss,best_epoch,parameters
0,Compact MLP,784 → 128 → 64 → 10,0.4909,82.8%,12,"109,386"
1,Wide MLP,784 → 512 → 256 → 128 → 10,0.4776,82.9%,12,"567,434"


In [35]:
fig = px.line(candidate_histories_df, x="epoch", y="val_accuracy", color="model", markers=True,
    color_discrete_map={"Compact MLP": "#06B6D4", "Wide MLP": "#EC4899"},
    title="Validation accuracy · candidate architecture pilot",
    labels={"epoch": "Epoch", "val_accuracy": "Validation accuracy", "model": "Candidate"})
fig.update_yaxes(tickformat=".0%", range=[0, 1])
fig.update_layout(height=430, legend=dict(orientation="h", y=1.12))
fig.show()

fig = px.bar(candidate_results_df, x="model", y="parameters", color="model", text_auto=",",
    color_discrete_sequence=["#06B6D4", "#EC4899"], title="Model capacity · parameter count",
    labels={"model": "Candidate", "parameters": "Trainable parameters"})
fig.update_layout(height=390, showlegend=False)
fig.show()

**Interpretation rule:** choose architecture and hyperparameters using validation evidence. Do not repeatedly inspect the test score while making design decisions; doing so turns the test set into another validation set.

## 08 · Final evaluation on the held-out test set

The best validation checkpoint is now frozen and evaluated on the test split. The evaluation reports accuracy, macro precision/recall/F1, a per-class report, and a confusion matrix. Macro metrics give each class equal weight, which is useful when class counts differ slightly.

In [36]:
# Collect predictions and probabilities once, using the restored best checkpoint.
y_true_batches = []
y_pred_batches = []
probability_batches = []

model.eval()
with torch.no_grad():
    for batch_features, batch_labels in test_loader:
        batch_features = batch_features.to(DEVICE)
        logits = model(batch_features)
        probabilities = torch.softmax(logits, dim=1)
        predictions = logits.argmax(dim=1)

        y_true_batches.append(batch_labels.numpy())
        y_pred_batches.append(predictions.cpu().numpy())
        probability_batches.append(probabilities.cpu().numpy())

y_true = np.concatenate(y_true_batches)
y_pred = np.concatenate(y_pred_batches)
y_prob = np.concatenate(probability_batches)

# Explicitly list all ten classes so absent classes would still be visible in the report.
class_ids = list(range(10))
class_labels = [CLASS_NAMES[class_id] for class_id in class_ids]

test_accuracy = accuracy_score(y_true, y_pred)
test_precision_macro = precision_score(y_true, y_pred, average="macro", zero_division=0)
test_recall_macro = recall_score(y_true, y_pred, average="macro", zero_division=0)
test_f1_macro = f1_score(y_true, y_pred, average="macro", zero_division=0)

metrics = {
    "test_accuracy": float(test_accuracy),
    "macro_precision": float(test_precision_macro),
    "macro_recall": float(test_recall_macro),
    "macro_f1": float(test_f1_macro),
    "best_epoch": best_epoch,
    "epochs_trained": int(len(history_df)),
    "training_seconds": float(training_seconds),
    "test_images": int(len(y_true)),
}

metric_cards = "".join([
    f'<div style="flex:1;min-width:150px;background:#F3F7FC;border:1px solid #E2EAF3;border-radius:12px;padding:16px 18px;">'
    f'<div style="font-size:12px;color:#64748B;font-weight:700;text-transform:uppercase;letter-spacing:1px;">{label}</div>'
    f'<div style="font-size:28px;color:#142238;font-weight:800;margin-top:6px;">{value}</div></div>'
    for label, value in [
        ("Test accuracy", f"{test_accuracy:.1%}"),
        ("Macro precision", f"{test_precision_macro:.1%}"),
        ("Macro recall", f"{test_recall_macro:.1%}"),
        ("Macro F1", f"{test_f1_macro:.1%}"),
    ]
])
display(HTML(f'<div style="display:flex;gap:12px;flex-wrap:wrap;margin:12px 0 20px 0;">{metric_cards}</div>'))

print("Classification report:")
report = classification_report(
    y_true,
    y_pred,
    labels=class_ids,
    target_names=class_labels,
    output_dict=True,
    zero_division=0,
)
report_df = pd.DataFrame(report).T
report_df = report_df.rename_axis("class / summary")
display(report_df.style.format({"precision": "{:.3f}", "recall": "{:.3f}", "f1-score": "{:.3f}", "support": "{:.0f}"}))

Classification report:


,precision,recall,f1-score,support
class / summary,,,,
T-shirt / Top,0.921,0.782,0.845,119
Trouser,0.966,0.975,0.970,118
Pullover,0.738,0.769,0.753,121
Dress,0.879,0.864,0.872,118
Coat,0.688,0.815,0.746,119
Sandal,0.974,0.927,0.950,123
Shirt,0.704,0.672,0.688,131
Sneaker,0.944,0.944,0.944,124
Bag,0.923,0.931,0.927,116


In [37]:
# 8.1 Confusion matrix — counts.
cm = confusion_matrix(y_true, y_pred, labels=class_ids)

fig = go.Figure(go.Heatmap(
    z=cm,
    x=class_labels,
    y=class_labels,
    colorscale="Blues",
    text=cm,
    texttemplate="%{text}",
    hovertemplate="Actual: %{y}<br>Predicted: %{x}<br>Images: %{z}<extra></extra>",
    colorbar=dict(title="Images"),
))
fig.update_layout(
    title="Confusion matrix · test set",
    xaxis_title="Predicted class",
    yaxis_title="Actual class",
    height=650,
    xaxis_tickangle=-35,
)
fig.update_yaxes(autorange="reversed")
fig.show()

In [38]:
# 8.2 Per-class precision, recall, F1 and accuracy.
per_class_rows = []
for class_id, class_name in zip(class_ids, class_labels):
    mask = y_true == class_id
    class_support = int(mask.sum())
    class_accuracy = float((y_pred[mask] == class_id).mean()) if class_support else 0.0
    per_class_rows.append({
        "class_id": class_id,
        "class_name": class_name,
        "precision": report[class_name]["precision"],
        "recall": report[class_name]["recall"],
        "f1_score": report[class_name]["f1-score"],
        "class_accuracy": class_accuracy,
        "support": class_support,
    })

per_class_df = pd.DataFrame(per_class_rows)
per_class_long = per_class_df.melt(
    id_vars=["class_id", "class_name"],
    value_vars=["precision", "recall", "f1_score", "class_accuracy"],
    var_name="metric",
    value_name="score",
)

fig = px.bar(
    per_class_long,
    x="class_name",
    y="score",
    color="metric",
    barmode="group",
    title="Class-level performance comparison",
    labels={"class_name": "Fashion category", "score": "Score", "metric": "Metric"},
    category_orders={"class_name": class_labels},
    color_discrete_sequence=["#2563EB", "#0F766E", "#F59E0B", "#8B5CF6"],
)
fig.update_yaxes(range=[0, 1.05], tickformat=".0%")
fig.update_xaxes(tickangle=-25)
fig.update_layout(height=500, legend=dict(orientation="h", y=1.12))
fig.show()

display(per_class_df.style.format({
    "precision": "{:.1%}", "recall": "{:.1%}", "f1_score": "{:.1%}", "class_accuracy": "{:.1%}", "support": "{:.0f}"
}))

,class_id,class_name,precision,recall,f1_score,class_accuracy,support
0,0,T-shirt / Top,92.1%,78.2%,84.5%,78.2%,119
1,1,Trouser,96.6%,97.5%,97.0%,97.5%,118
2,2,Pullover,73.8%,76.9%,75.3%,76.9%,121
3,3,Dress,87.9%,86.4%,87.2%,86.4%,118
4,4,Coat,68.8%,81.5%,74.6%,81.5%,119
5,5,Sandal,97.4%,92.7%,95.0%,92.7%,123
6,6,Shirt,70.4%,67.2%,68.8%,67.2%,131
7,7,Sneaker,94.4%,94.4%,94.4%,94.4%,124
8,8,Bag,92.3%,93.1%,92.7%,93.1%,116
9,9,Ankle boot,93.9%,96.4%,95.1%,96.4%,111


In [39]:
# 8.3 Prediction confidence — compare correct and incorrect predictions.
confidence = y_prob.max(axis=1)
correct_flags = y_true == y_pred
confidence_df = pd.DataFrame({
    "confidence": confidence,
    "prediction_status": np.where(correct_flags, "Correct", "Incorrect"),
})

fig = px.histogram(
    confidence_df,
    x="confidence",
    color="prediction_status",
    nbins=24,
    barmode="overlay",
    opacity=0.78,
    title="Model confidence on the test set",
    labels={"confidence": "Maximum predicted probability", "count": "Test images", "prediction_status": "Prediction"},
    color_discrete_map={"Correct": "#0F766E", "Incorrect": "#E76F51"},
)
fig.update_layout(height=420)
fig.show()

print(f"Mean confidence — correct predictions: {confidence[correct_flags].mean():.1%}")
if (~correct_flags).any():
    print(f"Mean confidence — incorrect predictions: {confidence[~correct_flags].mean():.1%}")

Mean confidence — correct predictions: 90.9%
Mean confidence — incorrect predictions: 66.0%


### 08.4 · Normalized confusion matrix

The count matrix answers “how many?”; the row-normalized matrix answers “what fraction of each true class was recognized?” The normalized view makes class-level recall differences easier to compare.

In [40]:
cm_normalized = cm / np.maximum(cm.sum(axis=1, keepdims=True), 1)
fig = go.Figure(go.Heatmap(
    z=cm_normalized, x=class_labels, y=class_labels, colorscale="Turbo", zmin=0, zmax=1,
    text=np.vectorize(lambda value: f"{value:.0%}")(cm_normalized), texttemplate="%{text}",
    hovertemplate="Actual: %{y}<br>Predicted: %{x}<br>Recall share: %{z:.1%}<extra></extra>",
    colorbar=dict(title="Row share", tickformat=".0%")
))
fig.update_yaxes(autorange="reversed")
fig.update_xaxes(tickangle=-35)
fig.update_layout(title="Normalized confusion matrix · row percentages", height=650, xaxis_title="Predicted class", yaxis_title="Actual class")
fig.show()

### 08.5 · Class metrics from multiple angles

In [41]:
# Radar view makes per-class strengths and weaknesses easy to scan.
radar_fig = go.Figure()
radar_metrics = [("Precision", "precision", "#2563EB"), ("Recall", "recall", "#F97316"), ("F1-score", "f1_score", "#10B981")]
for display_name, metric_column, color in radar_metrics:
    values = per_class_df[metric_column].tolist()
    radar_fig.add_trace(go.Scatterpolar(
        r=values + values[:1], theta=class_labels + class_labels[:1],
        fill="toself", name=display_name, line=dict(color=color, width=2.5), opacity=0.78
    ))
radar_fig.update_layout(
    title="Per-class performance radar", height=600,
    polar=dict(radialaxis=dict(visible=True, range=[0, 1], tickformat=".0%", gridcolor="#DDE5EF"),
               angularaxis=dict(gridcolor="#E6ECF3")),
    legend=dict(orientation="h", y=1.08)
)
radar_fig.show()

In [42]:
# Rank the most frequent class-to-class confusions, excluding the diagonal.
confusion_rows = []
for actual_id in class_ids:
    for predicted_id_value in class_ids:
        if actual_id != predicted_id_value and cm[actual_id, predicted_id_value] > 0:
            confusion_rows.append({
                "actual": CLASS_NAMES[actual_id], "predicted": CLASS_NAMES[predicted_id_value],
                "count": int(cm[actual_id, predicted_id_value]),
                "pair": f"{CLASS_NAMES[actual_id]} → {CLASS_NAMES[predicted_id_value]}"
            })
confusion_pairs_df = pd.DataFrame(confusion_rows).sort_values("count", ascending=False).head(15)
fig = px.bar(confusion_pairs_df.sort_values("count"), x="count", y="pair", orientation="h",
    color="count", color_continuous_scale="Turbo", text="count",
    title="Most frequent class confusions",
    labels={"count": "Misclassified images", "pair": "Actual → predicted"})
fig.update_traces(textposition="outside")
fig.update_layout(height=560, yaxis_title="")
fig.show()
display(confusion_pairs_df[["actual", "predicted", "count"]].reset_index(drop=True))

,actual,predicted,count
0,Pullover,Coat,20
1,Shirt,Coat,19
2,Shirt,Pullover,15
3,T-shirt / Top,Shirt,14
4,Coat,Pullover,10
5,Coat,Shirt,8
6,T-shirt / Top,Dress,6
7,Shirt,T-shirt / Top,6
8,Dress,Shirt,6
9,Pullover,Shirt,6


### 08.6 · Multiclass ROC and precision–recall curves

The following one-vs-rest charts treat each class as “positive” against all other classes. ROC-AUC summarizes ranking ability across thresholds; average precision summarizes the precision–recall curve. Both are threshold-independent summaries and should be read alongside class-wise precision/recall at the chosen argmax threshold.

In [43]:
from sklearn.preprocessing import label_binarize
from sklearn.metrics import roc_curve, auc, precision_recall_curve, average_precision_score

y_true_binary = label_binarize(y_true, classes=class_ids)
roc_fig = go.Figure()
roc_auc_rows = []
for class_id, class_name in zip(class_ids, class_labels):
    fpr, tpr, _ = roc_curve(y_true_binary[:, class_id], y_prob[:, class_id])
    class_auc = auc(fpr, tpr)
    roc_auc_rows.append({"class_name": class_name, "roc_auc": class_auc})
    roc_fig.add_trace(go.Scatter(x=fpr, y=tpr, mode="lines", name=f"{class_name} · {class_auc:.3f}",
        line=dict(color=FASHION_COLORS[class_id], width=2.3), hovertemplate="FPR %{x:.2f}<br>TPR %{y:.2f}<extra></extra>"))
roc_fig.add_trace(go.Scatter(x=[0, 1], y=[0, 1], mode="lines", name="Random baseline", line=dict(color="#64748B", dash="dash", width=1.5)))
roc_fig.update_layout(title="One-vs-rest ROC curves", xaxis_title="False positive rate", yaxis_title="True positive rate", height=580, xaxis=dict(range=[0,1]), yaxis=dict(range=[0,1]), legend=dict(font=dict(size=10)))
roc_fig.show()
roc_auc_df = pd.DataFrame(roc_auc_rows).sort_values("roc_auc", ascending=False)
display(roc_auc_df.style.format({"roc_auc": "{:.3f}"}).background_gradient(subset=["roc_auc"], cmap="GnBu"))

,class_name,roc_auc
1,Trouser,0.999
9,Ankle boot,0.999
7,Sneaker,0.998
5,Sandal,0.998
8,Bag,0.991
0,T-shirt / Top,0.991
3,Dress,0.989
2,Pullover,0.977
4,Coat,0.974
6,Shirt,0.958


In [44]:
pr_fig = go.Figure()
ap_rows = []
for class_id, class_name in zip(class_ids, class_labels):
    precision_curve, recall_curve, _ = precision_recall_curve(y_true_binary[:, class_id], y_prob[:, class_id])
    average_precision = average_precision_score(y_true_binary[:, class_id], y_prob[:, class_id])
    ap_rows.append({"class_name": class_name, "average_precision": average_precision})
    pr_fig.add_trace(go.Scatter(x=recall_curve, y=precision_curve, mode="lines",
        name=f"{class_name} · AP {average_precision:.3f}",
        line=dict(color=FASHION_COLORS[class_id], width=2.3),
        hovertemplate="Recall %{x:.2f}<br>Precision %{y:.2f}<extra></extra>"))
pr_fig.update_layout(title="One-vs-rest precision–recall curves", xaxis_title="Recall", yaxis_title="Precision", height=580, xaxis=dict(range=[0,1]), yaxis=dict(range=[0,1]), legend=dict(font=dict(size=10)))
pr_fig.show()
ap_df = pd.DataFrame(ap_rows).sort_values("average_precision", ascending=False)
fig = px.bar(ap_df.sort_values("average_precision"), x="average_precision", y="class_name", orientation="h",
    color="average_precision", color_continuous_scale="Turbo", text="average_precision",
    title="Average precision by class", labels={"average_precision": "Average precision", "class_name": "Category"})
fig.update_traces(texttemplate="%{text:.3f}", textposition="outside")
fig.update_layout(height=480)
fig.show()

### 08.7 · Confidence calibration and selective prediction

A 90% confidence score should not automatically be interpreted as “90% likely to be correct.” The reliability chart compares predicted top-class confidence with empirical accuracy in bins. The expected calibration error (ECE) below is a simple weighted summary of the absolute difference between those values; it is descriptive and depends on the chosen number of bins.

In [45]:
# Top-label calibration: bin each prediction by its maximum class probability.
calibration_bins = np.linspace(0.0, 1.0, 11)
bin_ids = np.digitize(confidence, calibration_bins[1:-1], right=True)
calibration_rows = []
for bin_index in range(len(calibration_bins) - 1):
    mask = bin_ids == bin_index
    if mask.any():
        calibration_rows.append({
            "bin": bin_index + 1,
            "lower": calibration_bins[bin_index], "upper": calibration_bins[bin_index + 1],
            "mean_confidence": float(confidence[mask].mean()),
            "observed_accuracy": float(correct_flags[mask].mean()),
            "count": int(mask.sum()),
        })
calibration_df = pd.DataFrame(calibration_rows)
ece = float(sum(row["count"] / len(confidence) * abs(row["mean_confidence"] - row["observed_accuracy"]) for _, row in calibration_df.iterrows()))
fig = go.Figure()
fig.add_trace(go.Scatter(x=calibration_df["mean_confidence"], y=calibration_df["observed_accuracy"],
    mode="lines+markers+text", text=calibration_df["count"], textposition="top center",
    name="Model reliability", line=dict(color="#2563EB", width=3), marker=dict(size=10),
    hovertemplate="Mean confidence %{x:.1%}<br>Observed accuracy %{y:.1%}<br>Images %{text}<extra></extra>"))
fig.add_trace(go.Scatter(x=[0,1], y=[0,1], mode="lines", name="Perfect calibration", line=dict(color="#F97316", dash="dash", width=2)))
fig.update_layout(title=f"Top-label reliability diagram · ECE = {ece:.3f}", xaxis_title="Mean predicted confidence", yaxis_title="Observed accuracy", height=470, xaxis=dict(range=[0,1], tickformat=".0%"), yaxis=dict(range=[0,1], tickformat=".0%"))
fig.show()
display(calibration_df.style.format({"lower": "{:.0%}", "upper": "{:.0%}", "mean_confidence": "{:.1%}", "observed_accuracy": "{:.1%}"}))

,bin,lower,upper,mean_confidence,observed_accuracy,count
0,3,20%,30%,25.6%,0.0%,3
1,4,30%,40%,37.1%,45.5%,11
2,5,40%,50%,45.5%,48.8%,43
3,6,50%,60%,54.7%,59.6%,89
4,7,60%,70%,64.7%,59.5%,79
5,8,70%,80%,75.8%,67.5%,80
6,9,80%,90%,85.2%,82.3%,124
7,10,90%,100%,98.4%,97.5%,771


In [46]:
# Risk–coverage curve: simulate abstaining on low-confidence predictions.
confidence_order = np.argsort(confidence)[::-1]
ordered_errors = (~correct_flags[confidence_order]).astype(int)
coverage = np.arange(1, len(ordered_errors) + 1) / len(ordered_errors)
cumulative_risk = np.cumsum(ordered_errors) / np.arange(1, len(ordered_errors) + 1)
fig = go.Figure(go.Scatter(x=coverage, y=cumulative_risk, mode="lines", line=dict(color="#8B5CF6", width=3), fill="tozeroy", fillcolor="rgba(139,92,246,0.12)", name="Selective risk"))
fig.update_layout(title="Selective prediction · error rate among retained predictions", xaxis_title="Coverage · share of predictions retained", yaxis_title="Cumulative error rate", height=430, xaxis=dict(tickformat=".0%", range=[0,1]), yaxis=dict(tickformat=".0%", range=[0,1]))
fig.show()

In [47]:
# Probability heatmap for a reproducible subset of test images.
probability_preview_count = min(60, len(y_true))
probability_preview_positions = np.linspace(0, len(y_true) - 1, probability_preview_count, dtype=int)
probability_preview = y_prob[probability_preview_positions]
customdata = np.column_stack([y_true[probability_preview_positions], y_pred[probability_preview_positions]])
fig = go.Figure(go.Heatmap(
    z=probability_preview, x=class_labels,
    y=[f"Test #{int(pos)}" for pos in probability_preview_positions],
    colorscale="Turbo", zmin=0, zmax=1,
    customdata=np.repeat(customdata[:, None, :], len(class_labels), axis=1),
    hovertemplate="%{y}<br>Class: %{x}<br>Probability: %{z:.1%}<br>True ID: %{customdata[0]}<br>Predicted ID: %{customdata[1]}<extra></extra>",
    colorbar=dict(title="Probability", tickformat=".0%")
))
fig.update_layout(title="Prediction-probability heatmap · selected test images", xaxis_title="Fashion category", yaxis_title="Test image", height=760, xaxis_tickangle=-35)
fig.show()

## 09 · Error analysis: what did the model get wrong?

A single accuracy number does not explain failure modes. This section displays incorrectly classified test images together with the true class, predicted class, and model confidence. Use the hover information and image labels to spot visually similar categories that are often confused.

In [48]:
misclassified_positions = np.flatnonzero(~correct_flags)
print(f"Misclassified test images: {len(misclassified_positions)} / {len(y_true)} ({len(misclassified_positions) / len(y_true):.1%})")

if len(misclassified_positions) == 0:
    print("No errors on this test split — inspect additional data before concluding the model generalizes perfectly.")
else:
    # Sort by confidence so the most confidently wrong predictions are visible first.
    ranked_errors = misclassified_positions[np.argsort(confidence[misclassified_positions])[::-1]]
    selected_errors = ranked_errors[:min(15, len(ranked_errors))]

    n_cols = 5
    n_rows = int(np.ceil(len(selected_errors) / n_cols))
    error_gallery = make_subplots(
        rows=n_rows,
        cols=n_cols,
        subplot_titles=[
            f"True: {CLASS_NAMES[int(y_true[pos])]}<br>Pred: {CLASS_NAMES[int(y_pred[pos])]} · {confidence[pos]:.0%}"
            for pos in selected_errors
        ],
        horizontal_spacing=0.035,
        vertical_spacing=0.12,
    )

    # Recover the original test image corresponding to each test-set position.
    for position, test_position in enumerate(selected_errors, start=1):
        row = (position - 1) // n_cols + 1
        col = (position - 1) % n_cols + 1
        image = X_test[test_position].reshape(28, 28) * 255.0
        error_gallery.add_trace(
            go.Heatmap(z=image, colorscale="gray", zmin=0, zmax=255, showscale=False, hoverinfo="skip"),
            row=row,
            col=col,
        )

    error_gallery.update_xaxes(visible=False, showgrid=False, zeroline=False)
    error_gallery.update_yaxes(visible=False, showgrid=False, zeroline=False, autorange="reversed")
    error_gallery.update_layout(
        title="Most confident misclassifications · test set",
        height=260 * n_rows,
        margin=dict(l=10, r=10, t=90, b=10),
    )
    error_gallery.show()

    error_table = pd.DataFrame({
        "test_position": selected_errors,
        "true_class": [CLASS_NAMES[int(y_true[pos])] for pos in selected_errors],
        "predicted_class": [CLASS_NAMES[int(y_pred[pos])] for pos in selected_errors],
        "confidence": [confidence[pos] for pos in selected_errors],
    })
    display(error_table.style.format({"confidence": "{:.1%}"}))

Misclassified test images: 166 / 1200 (13.8%)


,test_position,true_class,predicted_class,confidence
0,212,Sneaker,Ankle boot,99.7%
1,583,Dress,Trouser,98.8%
2,223,Coat,Pullover,97.1%
3,380,Pullover,Bag,96.1%
4,731,Coat,Pullover,96.0%
5,214,Pullover,Coat,95.5%
6,924,Coat,Bag,95.1%
7,1130,Sandal,Ankle boot,94.7%
8,1187,Trouser,Dress,94.5%
9,161,Shirt,Coat,94.4%


### Error-analysis questions

1. Are the mistakes concentrated in visually similar categories (for example, shirt, T-shirt/top, coat, and pullover)?
2. Does the model make some mistakes with unusually high confidence? Those are useful candidates for manual inspection.
3. Would a convolutional neural network be a better next experiment? For image data, a CNN can preserve local spatial patterns that a flattened MLP does not represent explicitly.

### 09.1 · Error concentration and ambiguous examples

In [49]:
# Error counts and error rates by actual class.
error_summary = per_class_df[["class_id", "class_name", "support", "class_accuracy"]].copy()
error_summary["errors"] = error_summary["support"] - np.rint(error_summary["class_accuracy"] * error_summary["support"]).astype(int)
error_summary["error_rate"] = 1 - error_summary["class_accuracy"]
fig = px.bar(error_summary.sort_values("error_rate"), x="error_rate", y="class_name", orientation="h",
    color="error_rate", color_continuous_scale="Turbo", text="error_rate",
    hover_data={"errors": True, "support": True}, title="Test error rate by true category",
    labels={"error_rate": "Error rate", "class_name": "True category"})
fig.update_traces(texttemplate="%{text:.1%}", textposition="outside")
fig.update_xaxes(tickformat=".0%", range=[0, max(0.25, float(error_summary["error_rate"].max()) * 1.2)])
fig.update_layout(height=470)
fig.show()

In [50]:
# View the least-confident examples: these are the model's most uncertain test predictions.
least_confident_positions = np.argsort(confidence)[:min(20, len(confidence))]
uncertainty_cols = 5
uncertainty_rows = int(np.ceil(len(least_confident_positions) / uncertainty_cols))
uncertainty_gallery = make_subplots(rows=uncertainty_rows, cols=uncertainty_cols,
    subplot_titles=[f"True: {CLASS_NAMES[int(y_true[pos])]}<br>Pred: {CLASS_NAMES[int(y_pred[pos])]} · {confidence[pos]:.0%}" for pos in least_confident_positions],
    horizontal_spacing=0.035, vertical_spacing=0.10)
for index, test_pos in enumerate(least_confident_positions, start=1):
    row, col = (index - 1) // uncertainty_cols + 1, (index - 1) % uncertainty_cols + 1
    uncertainty_gallery.add_trace(go.Heatmap(z=(X_test[test_pos].reshape(28,28) * 255), colorscale="gray", zmin=0, zmax=255, showscale=False, hoverinfo="skip"), row=row, col=col)
uncertainty_gallery.update_xaxes(visible=False); uncertainty_gallery.update_yaxes(visible=False, autorange="reversed")
uncertainty_gallery.update_layout(title="Lowest-confidence test predictions", height=260 * uncertainty_rows, margin=dict(t=90, l=10, r=10, b=10))
uncertainty_gallery.show()

In [51]:
# Compare confidence distributions for correct versus incorrect predictions with box + points.
confidence_status_df = pd.DataFrame({"confidence": confidence, "status": np.where(correct_flags, "Correct", "Incorrect")})
fig = px.violin(confidence_status_df, x="status", y="confidence", color="status", box=True, points="outliers",
    color_discrete_map={"Correct": "#10B981", "Incorrect": "#F43F5E"},
    title="Confidence distribution · correct versus incorrect predictions",
    labels={"status": "Outcome", "confidence": "Maximum class probability"})
fig.update_yaxes(tickformat=".0%", range=[0,1])
fig.update_layout(height=430, showlegend=False)
fig.show()

## 10 · Single-image inference

This cell demonstrates the model's inference path on one held-out test image. Change `TEST_IMAGE_POSITION` to inspect a different example. The cell displays the image, the predicted category, the true category, and the full class-probability distribution.

In [52]:
TEST_IMAGE_POSITION = 0  # Change this value to inspect another image in the test split.
if not 0 <= TEST_IMAGE_POSITION < len(X_test):
    raise IndexError(f"Choose a test position between 0 and {len(X_test) - 1}.")

sample_tensor = torch.tensor(X_test[TEST_IMAGE_POSITION], dtype=torch.float32).unsqueeze(0).to(DEVICE)
model.eval()
with torch.no_grad():
    sample_logits = model(sample_tensor)
    sample_probabilities = torch.softmax(sample_logits, dim=1).cpu().numpy()[0]

predicted_id = int(sample_probabilities.argmax())
actual_id = int(y_test[TEST_IMAGE_POSITION])

fig = make_subplots(
    rows=1,
    cols=2,
    column_widths=[0.42, 0.58],
    subplot_titles=("Input image", "Class probabilities"),
)
fig.add_trace(
    go.Heatmap(z=(X_test[TEST_IMAGE_POSITION].reshape(28, 28) * 255), colorscale="gray", zmin=0, zmax=255, showscale=False, hoverinfo="skip"),
    row=1,
    col=1,
)
fig.add_trace(
    go.Bar(
        x=class_labels,
        y=sample_probabilities,
        marker_color=["#0F766E" if idx == predicted_id else "#CBD5E1" for idx in class_ids],
        hovertemplate="%{x}<br>Probability: %{y:.1%}<extra></extra>",
        showlegend=False,
    ),
    row=1,
    col=2,
)
fig.update_xaxes(visible=False, showgrid=False, zeroline=False, row=1, col=1)
fig.update_yaxes(visible=False, showgrid=False, zeroline=False, autorange="reversed", row=1, col=1)
fig.update_xaxes(tickangle=-35, row=1, col=2)
fig.update_yaxes(title_text="Probability", tickformat=".0%", range=[0, 1], row=1, col=2)
fig.update_layout(
    title=f"Prediction: {CLASS_NAMES[predicted_id]} · confidence {sample_probabilities[predicted_id]:.1%} · actual: {CLASS_NAMES[actual_id]}",
    height=460,
)
fig.show()

### 10.1 · Batch inference gallery

This view runs inference over a small batch of held-out images and displays the true class, predicted class, and confidence together. It is a practical way to sanity-check model behavior beyond a single hand-picked image.

In [53]:
inference_gallery_positions = np.linspace(0, len(X_test) - 1, min(20, len(X_test)), dtype=int)
inference_cols = 5
inference_rows = int(np.ceil(len(inference_gallery_positions) / inference_cols))
inference_gallery = make_subplots(rows=inference_rows, cols=inference_cols,
    subplot_titles=[f"{'✓' if y_true[pos] == y_pred[pos] else '✕'} {CLASS_NAMES[int(y_pred[pos])]}<br>True: {CLASS_NAMES[int(y_true[pos])]} · {confidence[pos]:.0%}" for pos in inference_gallery_positions],
    horizontal_spacing=0.035, vertical_spacing=0.09)
for index, test_pos in enumerate(inference_gallery_positions, start=1):
    row, col = (index - 1) // inference_cols + 1, (index - 1) % inference_cols + 1
    inference_gallery.add_trace(go.Heatmap(z=X_test[test_pos].reshape(28,28), colorscale="gray", zmin=0, zmax=1, showscale=False, hoverinfo="skip"), row=row, col=col)
inference_gallery.update_xaxes(visible=False); inference_gallery.update_yaxes(visible=False, autorange="reversed")
inference_gallery.update_layout(title="Batch inference review · checkmark = correct, cross = incorrect", height=270 * inference_rows, margin=dict(t=90, l=10, r=10, b=10))
inference_gallery.show()

### 10.2 · Hidden-layer representation analysis

The penultimate layer compresses each input into a 64-dimensional learned representation. PCA on these activations provides a visual check of whether examples from the same category tend to cluster. This is a qualitative diagnostic, not a formal separability test.

In [54]:
# Extract the 64-dimensional representation immediately before the final classifier.
feature_extractor = nn.Sequential(*list(model.network.children())[:-1]).to(DEVICE)
feature_extractor.eval()
activation_batches = []
with torch.no_grad():
    for start in range(0, len(X_test), 256):
        batch_tensor = torch.tensor(X_test[start:start+256], dtype=torch.float32, device=DEVICE)
        activation_batches.append(feature_extractor(batch_tensor).cpu().numpy())
test_embeddings = np.vstack(activation_batches)
embedding_pca = PCA(n_components=2, random_state=SEED)
embedding_coordinates = embedding_pca.fit_transform(test_embeddings)
embedding_df = pd.DataFrame({
    "PC1": embedding_coordinates[:,0], "PC2": embedding_coordinates[:,1],
    "class_name": [CLASS_NAMES[int(value)] for value in y_true],
    "correct": np.where(correct_flags, "Correct", "Incorrect"),
    "confidence": confidence,
})
fig = px.scatter(embedding_df, x="PC1", y="PC2", color="class_name", symbol="correct",
    color_discrete_sequence=FASHION_COLORS, opacity=0.76,
    hover_data={"confidence": ":.1%", "correct": True},
    title=f"Learned test-set representations · 64D → 2D PCA ({embedding_pca.explained_variance_ratio_.sum():.1%} variance shown)")
fig.update_traces(marker=dict(size=7, line=dict(width=0.25, color="white")))
fig.update_layout(height=590, legend_title="Category / outcome")
fig.show()

In [55]:
# First-layer absolute weight magnitude, aggregated across all 256 hidden units.
first_dense_weights = model.network[0].weight.detach().cpu().numpy()
input_weight_map = np.linalg.norm(first_dense_weights, axis=0).reshape(28, 28)
fig = go.Figure(go.Heatmap(z=input_weight_map, colorscale="Turbo",
    hovertemplate="Input pixel (%{y}, %{x})<br>Aggregated |weight|: %{z:.3f}<extra></extra>",
    colorbar=dict(title="L2 magnitude")))
fig.update_yaxes(autorange="reversed", title="Pixel row")
fig.update_xaxes(title="Pixel column")
fig.update_layout(title="Input-layer weight magnitude map", height=450)
fig.show()
print("Interpretation caution: this is a weight-magnitude summary, not a causal feature-importance or saliency map.")

Interpretation caution: this is a weight-magnitude summary, not a causal feature-importance or saliency map.


In [56]:
# Inspect the activation distribution at each hidden ReLU layer and estimate inactive-unit share.
activation_values = {"Hidden 1 · 256 units": [], "Hidden 2 · 128 units": [], "Hidden 3 · 64 units": []}
model.eval()
with torch.no_grad():
    for start in range(0, min(600, len(X_test)), 128):
        xb = torch.tensor(X_test[start:start+128], dtype=torch.float32, device=DEVICE)
        z1 = torch.relu(model.network[0](xb))
        z2 = torch.relu(model.network[3](model.network[2](z1)))
        z3 = torch.relu(model.network[6](model.network[5](z2)))
        activation_values["Hidden 1 · 256 units"].append(z1.cpu().numpy().ravel())
        activation_values["Hidden 2 · 128 units"].append(z2.cpu().numpy().ravel())
        activation_values["Hidden 3 · 64 units"].append(z3.cpu().numpy().ravel())

activation_fig = go.Figure()
activation_summary_rows = []
for idx, (layer_name, chunks) in enumerate(activation_values.items()):
    values = np.concatenate(chunks)
    activation_fig.add_trace(go.Histogram(x=values, name=layer_name, opacity=0.52, nbinsx=60, marker_color=FASHION_COLORS[idx]))
    activation_summary_rows.append({"layer": layer_name, "mean_activation": float(values.mean()), "zero_activation_share": float((values == 0).mean()), "activation_std": float(values.std())})
activation_fig.update_layout(title="Hidden-layer activation distributions", barmode="overlay", xaxis_title="ReLU activation", yaxis_title="Frequency", height=460, legend=dict(orientation="h", y=1.12))
activation_fig.show()
activation_summary_df = pd.DataFrame(activation_summary_rows)
display(activation_summary_df.style.format({"mean_activation": "{:.3f}", "zero_activation_share": "{:.1%}", "activation_std": "{:.3f}"}).background_gradient(subset=["zero_activation_share"], cmap="YlOrRd"))

,layer,mean_activation,zero_activation_share,activation_std
0,Hidden 1 · 256 units,0.368,59.0%,0.638
1,Hidden 2 · 128 units,1.037,41.0%,1.365
2,Hidden 3 · 64 units,2.070,35.3%,2.552


## 11 · Save the model and experiment outputs

The export section saves the model weights, label mapping, key configuration, and evaluation metrics. A PyTorch `state_dict` is preferred over serializing an entire Python model object because it is more portable and avoids depending on the original class instance during loading.

In [57]:
ARTIFACT_DIR = Path("artifacts")
ARTIFACT_DIR.mkdir(parents=True, exist_ok=True)

checkpoint_path = ARTIFACT_DIR / "fashion_ann_pytorch.pth"
metrics_path = ARTIFACT_DIR / "test_metrics.json"
history_path = ARTIFACT_DIR / "training_history.csv"

checkpoint = {
    "model_state_dict": {key: value.detach().cpu() for key, value in model.state_dict().items()},
    "input_features": int(X_train.shape[1]),
    "num_classes": int(len(CLASS_NAMES)),
    "class_names": CLASS_NAMES,
    "seed": SEED,
    "best_epoch": best_epoch,
    "architecture": "784-256-128-64-10 MLP with ReLU and dropout",
}
torch.save(checkpoint, checkpoint_path)

with open(metrics_path, "w", encoding="utf-8") as file:
    json.dump(metrics, file, indent=4)

history_df.to_csv(history_path, index=False)

print("Saved artifacts:")
for artifact in [checkpoint_path, metrics_path, history_path]:
    print(f"  ✓ {artifact.resolve()} ({artifact.stat().st_size:,} bytes)")

Saved artifacts:
  ✓ /content/artifacts/fashion_ann_pytorch.pth (974,965 bytes)
  ✓ /content/artifacts/test_metrics.json (279 bytes)
  ✓ /content/artifacts/training_history.csv (2,780 bytes)


In [58]:
# Optional: reload the checkpoint into a fresh model and verify inference works.
loaded_checkpoint = torch.load(checkpoint_path, map_location=DEVICE, weights_only=True)
reloaded_model = FashionANN(
    input_features=loaded_checkpoint["input_features"],
    num_classes=loaded_checkpoint["num_classes"],
).to(DEVICE)
reloaded_model.load_state_dict(loaded_checkpoint["model_state_dict"])
reloaded_model.eval()

with torch.no_grad():
    reload_logits = reloaded_model(sample_tensor)
    reload_prediction = int(reload_logits.argmax(dim=1).item())

assert reload_prediction == predicted_id, "Reloaded checkpoint prediction differs from the current model."
print(f"Checkpoint reload verification: PASSED | sample prediction = {CLASS_NAMES[reload_prediction]}")

Checkpoint reload verification: PASSED | sample prediction = Sandal


## 12 · Final assessment & next steps

### What this notebook establishes

- A validated pipeline for the supplied 6,000-image CSV.
- A stratified and normalized data split with a true holdout test set.
- A fully connected PyTorch ANN trained with validation-based checkpoint selection.
- Interactive Plotly views for data exploration, training diagnostics, test performance, and error analysis.
- Reusable model weights and experiment logs saved under `artifacts/`.

### Limitations to state honestly

- This CSV is a **small sample**, not the full 70,000-image Fashion-MNIST benchmark. Results should not be compared directly with published full-dataset scores without matching the data, split, and protocol.
- An MLP does not exploit image locality as naturally as a CNN. A convolutional baseline is the most meaningful next model comparison.
- Accuracy alone does not capture every failure mode. Review the per-class metrics and high-confidence errors before making claims about practical reliability.
- The class-name mapping assumes the standard Fashion-MNIST label convention. Confirm this mapping against the dataset's original source if the CSV was transformed or relabeled.

### Suggested next experiments

1. Train a small CNN on the same fixed split and compare macro-F1, accuracy, training time, and confusion matrices.
2. Compare optimizers (AdamW vs. SGD with momentum) and learning rates using the validation set only.
3. Add a calibration check (for example, expected calibration error) before interpreting predicted probabilities as confidence.
4. Repeat the experiment with multiple random seeds and report mean ± standard deviation.
5. Inspect incorrectly classified images and consider whether label ambiguity or data quality contributes to the errors.

---

<div align="center">

**End of notebook**  
*Clean data. Careful experiments. Clear evidence.*

</div>

## 13 · Extended dashboard guide and reproducibility notes

### New visual layers in this enhanced edition

| Area | Additional visuals | What they help answer |
|---|---|---|
| Dataset profiling | Violin plots, treemap, class templates, pixel variability maps | Are classes balanced? How do image statistics differ? |
| Data preparation | Split balance, normalization comparison, batch gallery | Did the data pipeline preserve labels and scale correctly? |
| Architecture | Sankey layer map, parameter budget, weight distributions | Where does model capacity sit? |
| Optimization | Generalization gaps, epoch time, log-loss trajectory | Is training stable? Is validation behavior diverging? |
| Model selection | Compact versus wide MLP validation pilot | Does additional capacity help on validation data? |
| Evaluation | Normalized confusion matrix, radar, ROC, PR, calibration | Which classes are reliable, and how do thresholds behave? |
| Error review | Most frequent confusions, uncertain examples, error rates | What mistakes deserve inspection? |
| Representation | Hidden-layer PCA, first-layer weight map, activation distributions | What patterns does the network encode? |

### Reproducibility checklist

1. Keep `fmnist_small.csv` beside the notebook, or update `DATA_PATH`.
2. Run cells from top to bottom in a fresh kernel.
3. Record any changes to `SEED`, `BATCH_SIZE`, architecture, optimizer, or learning-rate settings.
4. Use validation metrics for all architecture and hyperparameter decisions.
5. Evaluate the final selected model on the test set once and report the exact split protocol.

**Important:** visual complexity does not automatically make a model better. The charts are intended to make evidence easier to inspect, not to inflate the reported performance. The supplied file is a 6,000-image sample, so results describe this split and sample rather than the full Fashion-MNIST benchmark.